In [1]:
import numpy as np
import math

def evaluar(poblacion, funcion):
    """Evalúa todas las soluciones de una población."""
    return np.array(
        [funcion(x) for x in poblacion],
        dtype=float
    )

def clonalg(
    funcion,
    limites,
    tamano=30,
    iteraciones=100,
    seleccion=10,
    clones_max=12,
    tasa_mutacion=0.15,
    nuevos=3,
    semilla=42
):
    rng = np.random.default_rng(semilla)

    limites = np.asarray(limites, dtype=float)
    inferior = limites[:, 0]
    superior = limites[:, 1]
    dimension = len(inferior)

    # 1. Crear población inicial de anticuerpos.
    poblacion = rng.uniform(
        inferior, superior, (tamano, dimension)
    )

    # 2. Evaluar la calidad de cada anticuerpo.
    errores = evaluar(poblacion, funcion)
   
    indice = np.argmin(errores)
    mejor_global = poblacion[indice].copy()
    error_global = errores[indice]

    historial = [error_global]
    instantaneas = [poblacion.copy()]
    etapas = []

    seleccion = min(seleccion, tamano)

    # 3. Ciclo de evolución.
    for paso in range(1, iteraciones + 1):
        poblacion_previa = poblacion.copy()

        # Ordenar de menor a mayor error.
        orden = np.argsort(errores)

        # 4. Seleccionar los mejores anticuerpos.
        elegidos = poblacion[orden[:seleccion]]

        grupos_clones = []
        padres_de_clones = []

        

        # 5. Clonar y mutar cada seleccionado.
        for rango, padre in enumerate(elegidos):

            # Los mejores generan más clones.
            cantidad = max(
                1,
                round(
                    clones_max
                    * (seleccion - rango)
                    / seleccion
                )
            )

            # Rango relativo: 0 es el mejor anticuerpo.
            proporcion = rango / max(1, seleccion - 1)

            # Los mejores mutan menos.
            # La mutación también disminuye con el tiempo.
            intensidad = (
                tasa_mutacion
                * (superior - inferior)
                * (0.2 + 0.8 * proporcion)
                * (1.0 - 0.7 * (paso - 1) / iteraciones)
            )

            # 6. Generar descendientes mutados.
            mutaciones = rng.normal(
                0,
                intensidad,
                size=(cantidad, dimension)
            )

            clones = np.clip(
                padre + mutaciones,
                inferior,
                superior
            )

            grupos_clones.append(clones)
            padres_de_clones.append(np.repeat(padre[None, :], cantidad, axis=0))#

        hijos = np.vstack(grupos_clones)
        
        padres_hijos = np.vstack(padres_de_clones)#

        # 7. Combinar padres y descendientes.
        candidatos = np.vstack([poblacion, hijos])
        

        # 8. Evaluar todos los candidatos.
        errores_candidatos = evaluar(
            candidatos, funcion
        )

        # 9. Conservar las mejores soluciones.
        supervivientes = tamano - nuevos

        mejores = np.argsort(
            errores_candidatos
        )[:supervivientes]

        # 10. Introducir anticuerpos aleatorios nuevos.
        aleatorios = rng.uniform(
            inferior,
            superior,
            size=(nuevos, dimension)
        )

        poblacion = np.vstack([
            candidatos[mejores],
            aleatorios
        ])
        
        supervivientes_pts = candidatos[mejores].copy()#


        errores = evaluar(poblacion, funcion)

        # 11. Actualizar la memoria global.
        indice = np.argmin(errores)

        if errores[indice] < error_global:
            mejor_global = poblacion[indice].copy()
            error_global = errores[indice]

        historial.append(error_global)

        
        instantaneas.append(poblacion.copy())
        etapas.append({
            'anterior': poblacion_previa,
            'seleccionados': elegidos,
            'clones': hijos.copy(),
            'padres_clones': padres_hijos,
            'supervivientes': supervivientes_pts,
            'aleatorios': aleatorios.copy(),
            'poblacion': poblacion.copy(),
            'mejor': mejor_global.copy(),
            'error': error_global,
        })#

    return {
        "posicion": mejor_global,
        "error": error_global,
        "historial": np.array(historial),
        "instantaneas": instantaneas,
        "etapas": etapas,
        "limites": limites
    }

In [2]:
import matplotlib.pyplot as plt
from matplotlib.colors import LogNorm
from matplotlib.animation import FuncAnimation, PillowWriter

plt.rcParams['animation.embed_limit'] = 300


def animar_clonalg(resultado, funcion=None, intervalo=250, guardar=None,
                   cada=1, mostrar=True, minimo_teorico=None):
    """Anima CLONALG usando x[0], x[1] y un paisaje 2D.

    funcion: función objetivo de vectores (por defecto, la usada en clonalg).
    minimo_teorico: coordenadas conocidas del mínimo, o None para no mostrarlo.
    cada: muestra una de cada N iteraciones (siempre incluye la última).
    guardar: ruta opcional para exportar un GIF usando Pillow.
    """
    if funcion is None:
        funcion = resultado.get('funcion')
    if funcion is None:
        raise ValueError('Debes pasar funcion=... a animar_clonalg().')

    limites = np.asarray(resultado['limites'], dtype=float)
    dimension = len(limites)
    if dimension < 2:
        raise ValueError('Para la gráfica se requieren al menos 2 dimensiones.')
    if cada < 1 or intervalo <= 0:
        raise ValueError('cada debe ser >= 1 e intervalo debe ser > 0.')
    if not resultado['etapas']:
        raise ValueError('No hay iteraciones para animar.')

    x = np.linspace(limites[0, 0], limites[0, 1], 220)
    y = np.linspace(limites[1, 0], limites[1, 1], 220)
    X, Y = np.meshgrid(x, y)

    # El paisaje es una sección 2D de la función N-dimensional.
    # Fijamos las dimensiones ocultas al mejor resultado global obtenido.
    referencia = np.asarray(resultado['posicion'], dtype=float)
    coordenadas = np.tile(referencia, (X.size, 1))
    coordenadas[:, 0] = X.ravel()
    coordenadas[:, 1] = Y.ravel()
    Z = evaluar(coordenadas, funcion).reshape(X.shape)
    if not np.all(np.isfinite(Z)):
        raise ValueError('La función devuelve valores no finitos en el paisaje.')

    fig, (ax, ax_error) = plt.subplots(
        1, 2, figsize=(18, 8), gridspec_kw={'width_ratios': [1.4, 1]}
    )
    fig.subplots_adjust(wspace=0.34, bottom=0.19)

    # Escala logarítmica para superficies no negativas (como Beale/Rastrigin).
    # Para funciones con negativos se usa la escala lineal, que admite ambos signos.
    zmin, zmax = float(Z.min()), float(Z.max())
    if zmin >= 0 and zmax > 0:
        vmin = min(0.01, zmax / 1000)
        vmin = max(vmin, 1e-15)
        z_dibujo = np.maximum(Z, vmin)
        norm = LogNorm(vmin=vmin, vmax=max(zmax, vmin * 10))
    else:
        z_dibujo = Z
        norm = Normalize(vmin=zmin, vmax=zmax if zmax > zmin else zmin + 1)
    imagen = ax.pcolormesh(X, Y, z_dibujo, shading='auto', cmap='viridis', norm=norm)
    niveles = [v for v in [0.01, 0.1, 1, 10, 100, 1000, 10000]
               if zmin < v < zmax]
    if niveles:
        ax.contour(X, Y, Z, levels=niveles, colors='white', alpha=0.4,
                   linewidths=0.65)
    fig.colorbar(imagen, ax=ax, label='f(x) (corte 2D)', fraction=0.046, pad=0.04)
    ax.set(xlim=limites[0], ylim=limites[1], xlabel='x[0]', ylabel='x[1]')

    if minimo_teorico is not None:
        minimo = np.asarray(minimo_teorico, dtype=float)
        if minimo.ndim != 1 or len(minimo) < 2:
            raise ValueError('minimo_teorico debe contener al menos dos coordenadas.')
        ax.plot(minimo[0], minimo[1], 'w+', ms=10, mew=2,
                label='Mínimo teórico (proyección)')

    if dimension > 2:
        ax.text(0.5, -0.14,
                f'Corte de {dimension}D: x[2:] fijadas en la mejor solución. '
                'Puntos = proyecciones.',
                transform=ax.transAxes, ha='center', fontsize=8)

    historial = np.asarray(resultado['historial'], dtype=float)
    escala_error_log = bool(np.all(historial >= 0))
    hist_dibujo = np.maximum(historial, 1e-12) if escala_error_log else historial
    ax_error.plot(np.arange(len(historial)), hist_dibujo,
                  color='0.7', lw=1, label='Historial completo')
    progreso, = ax_error.plot([], [], color='tab:red', lw=2,
                             label='Hasta la iteración actual')
    indicador, = ax_error.plot([], [], 'o', color='black')
    ax_error.set(xlabel='Iteración', ylabel='Mejor error global',
                 title='Convergencia', xlim=(0, max(1, len(historial) - 1)))
    ax_error.set_yscale('log' if escala_error_log else 'symlog')
    ax_error.legend(loc='upper right', fontsize=8)

    pasos = list(range(0, len(resultado['etapas']), cada))
    if pasos[-1] != len(resultado['etapas']) - 1:
        pasos.append(len(resultado['etapas']) - 1)
    fotogramas = [(i, fase) for i in pasos for fase in range(4)]
    nombres = ['1/4 Selección', '2/4 Clonación y mutación',
               '3/4 Supervivencia', '4/4 Nuevos anticuerpos']

    def actualizar(numero):
        i, fase = fotogramas[numero]
        d = resultado['etapas'][i]
        for artista in list(ax.collections):
            if getattr(artista, '_es_clonalg', False):
                artista.remove()
        for artista in list(ax.lines):
            if getattr(artista, '_es_clonalg', False):
                artista.remove()

        def puntos(xy, **kwargs):
            s = ax.scatter(xy[:, 0], xy[:, 1], **kwargs)
            s._es_clonalg = True
            return s

        if fase == 0:
            puntos(d['anterior'], c='black', s=19, alpha=0.6, label='Población')
            puntos(d['seleccionados'], c='deepskyblue', s=60, marker='D',
                   edgecolors='black', linewidths=0.5, label='Seleccionados')
        elif fase == 1:
            puntos(d['seleccionados'], c='deepskyblue', s=65, marker='D',
                   edgecolors='black', linewidths=0.5, label='Padres')
            for padre, clon in zip(d['padres_clones'], d['clones']):
                l, = ax.plot([padre[0], clon[0]], [padre[1], clon[1]],
                             color='black', alpha=0.5, lw=0.5)
                l._es_clonalg = True
            puntos(d['clones'], c='red', edgecolors='black', s=12, alpha=0.8, label='Clones mutados')
        elif fase == 2:
            puntos(d['supervivientes'], c='lime', s=35, edgecolors='black',
                   linewidths=0.35, label='Supervivientes')
        else:
            puntos(d['supervivientes'], c='lime', s=35, edgecolors='black', linewidths=0.35, alpha=0.8,
                   label='Supervivientes')
            if len(d['aleatorios']):
                puntos(d['aleatorios'], c='magenta', marker='x', s=65,
                       label='Nuevos aleatorios')
        puntos(d['mejor'][None, :], c='gold', s=210, marker='*',
               edgecolors='black', linewidths=0.7, label='Mejor global')
        ax.set_title(f'CLONALG | Iteración {i+1} | {nombres[fase]}')
        leyenda = ax.get_legend()
        if leyenda is not None:
            leyenda.remove()
        ax.legend(loc='upper left', fontsize=8)
        progreso.set_data(np.arange(i + 2), hist_dibujo[:i+2])
        indicador.set_data([i + 1], [hist_dibujo[i + 1]])
        ax_error.set_title(f'Mejor error: {d["error"]:.3g}')
        return []

    animacion = FuncAnimation(fig, actualizar, frames=len(fotogramas),
                              interval=intervalo, repeat=True, blit=False)
    if guardar:
        animacion.save(guardar, writer=PillowWriter(fps=max(1, round(1000 / intervalo))))
        print('Animación guardada en:', guardar)
    if mostrar:
        plt.show()
    else:
        plt.close(fig)
    return animacion

In [3]:
from IPython.display import HTML, display

f = lambda x: \
    10*len(x) + np.sum(x**2 - 10*np.cos(2*math.pi*x))
    #    (x[0] + 2 * x[1] - 7)**2 + (2 * x[0] + x[1] - 5)**2

    #np.sum(x**2)

    
    #(1.5 - x[0] +x[0]*x[1])**2 + (2.25 - x[0] + x[0]*x[1]**2)**2 + (2.625 - x[0] + x[0]*x[1]**3)**2

    #-20*np.exp(-0.2*np.sqrt(0.5*(x[0]**2+x[1]**2)))-np.exp(0.5*(np.cos(2*np.pi*x[0])+np.cos(2*np.pi*x[1])))+ np.e + 20
    
dimensiones = 2
limites = [(-5.12,5.12)] * dimensiones
result =  clonalg(
    funcion=f,
    limites=limites,
    iteraciones=50,
    tamano=20,
    semilla=10
)
print("Mejor posición:", result["posicion"])
print("Mejor error:", result["error"])
# Mostrar 1 de cada 5 iteraciones para evitar sobrecargar el navegador
animacion = animar_clonalg(result,funcion=f, cada=1, intervalo=5000, mostrar=False)
display(HTML(animacion.to_jshtml()))


Mejor posición: [-0.00137299 -0.000333  ]
Mejor error: 0.0003959843188248158


In [4]:
%pip install imageio-ffmpeg

Note: you may need to restart the kernel to use updated packages.



[notice] A new release of pip is available: 25.3 -> 26.2.1
[notice] To update, run: python.exe -m pip install --upgrade pip


In [5]:
import matplotlib as mpl
import imageio_ffmpeg

mpl.rcParams['animation.ffmpeg_path'] = imageio_ffmpeg.get_ffmpeg_exe()

animacion.save("clonalg.mp4", writer="ffmpeg", fps=4, dpi=120)